## PLN 2026 - Aula 6
Prof. Maiko Spiess



---



## Análise de Descrições de Jogos

Este notebook tem como objetivo explorar técnicas de Processamento de Linguagem Natural (PLN) para analisar e agrupar descrições de diferentes jogos. As etapas incluem:

1.  **Carregamento dos Dados**: Importação de um conjunto de dados sintético contendo `id`, `animal`, `categoria` e `descricao`.
2.  **Preparação dos Textos**: Limpeza e normalização das descrições textuais (tokenização, conversão para minúsculas, remoção de pontuação e stopwords).
3.  **Representação Numérica**: Transformação das descrições em vetores numéricos usando:
    *   **Bag of Words (BoW)**: Representação baseada na frequência das palavras.
    *   **TF-IDF (Term Frequency-Inverse Document Frequency)**: Representação que atribui pesos às palavras com base em sua importância relativa.
4.  **Cálculo de Similaridade**: Determinação da similaridade entre as descrições utilizando a similaridade do cosseno para as representações BoW e TF-IDF.
5.  **Agrupamento (Clustering)**: Aplicação do algoritmo K-Means para agrupar automaticamente as descrições semelhantes com base em suas representações TF-IDF.
6.  **Análise de Clusters**: Visualização dos clusters usando PCA (Análise de Componentes Principais) em 2D e 3D, interpretação dos clusters por meio de seus termos mais representativos, e avaliação da coesão e distância entre eles.

## Carregando a base de dados

Nesta atividade, vamos trabalhar com uma base de dados sintética contendo descrições curtas de diferentes jogos.

Cada linha da base possui:

- um identificador (`id`);
- o nome do jogo (`animal`);
- sua categoria (`categoria`);
- uma breve descrição textual (`descricao`).

Ao longo da atividade, utilizaremos principalmente a coluna `descricao` para criar representações numéricas dos textos e comparar os jogos entre si.

In [20]:
import ast
import pandas as pd

# Carregar os dados locais
df = pd.read_csv("jogos_nlp_completo.csv")

# Converter string de lista para lista Python real
df["tokens_sem_stopwords"] = df["tokens_sem_stopwords"].apply(
    ast.literal_eval
)

# Mapeamento para manter compatibilidade com o notebook
df = df.rename(
    columns={
        "Posicao": "id",
        "Nome": "animal",  # Título/Label do jogo
        "Tags": "categoria",  # Categoria para crosstab/PCA
    }
)

# Simplificar a categoria para o gênero primário
df["categoria"] = df["categoria"].apply(
    lambda x: str(x).split(",")[0].strip()
)

# Texto contínuo limpo para tooltips e visualizações
df["descricao"] = df["tokens_sem_stopwords"].apply(lambda t: " ".join(t))

# Manter somente as colunas utilizadas no restante da análise
df = df[["id", "animal", "categoria", "descricao", "tokens_sem_stopwords"]]

df.head()

,id,animal,categoria,descricao,tokens_sem_stopwords
0,1,Grand Theft Auto V,Adventure,vast open world set los santos sprawling metro...,"[vast, open, world, set, los, santos, sprawlin..."
1,2,Red Dead Redemption 2,Adventure,epic tale outlaw arthur morgan infamous van de...,"[epic, tale, outlaw, arthur, morgan, infamous,..."
2,3,Elden Ring,Adventure,action rpg developed published released februa...,"[action, rpg, developed, published, released, ..."
3,4,Minecraft: Java Edition,Adventure,focuses allowing player explore interact modif...,"[focuses, allowing, player, explore, interact,..."
4,5,The Legend of Zelda: Breath of the Wild,Adventure,first series link travel anywhere equipped wea...,"[first, series, link, travel, anywhere, equipp..."


## Representação 1 — Bag of Words (BoW)

O **Bag of Words (BoW)** representa cada documento pela frequência das palavras que aparecem nele.

Podemos imaginar uma grande tabela em que:

- cada **linha** representa um jogo;
- cada **coluna** representa uma palavra do vocabulário;
- cada **célula** informa quantas vezes aquela palavra aparece na descrição.

A ordem das palavras é ignorada. Assim, o texto passa a ser representado apenas pelas palavras que contém e por suas frequências.

Vamos utilizar os tokens já normalizados e sem *stopwords*. O campo `id` será mantido para que cada representação possa ser relacionada posteriormente à base original.

In [21]:
from sklearn.feature_extraction.text import CountVectorizer

# Criar o modelo Bag of Words
# Como os textos já estão tokenizados, usamos diretamente as listas de tokens
bow_vectorizer = CountVectorizer(
    analyzer=lambda tokens: tokens
)

# Criar a matriz Bag of Words
bow_matrix = bow_vectorizer.fit_transform(
    df["tokens_sem_stopwords"]
)

# Recuperar o vocabulário
bow_palavras = bow_vectorizer.get_feature_names_out()

# Transformar a matriz em DataFrame
df_bow = pd.DataFrame(
    bow_matrix.toarray(),
    columns=bow_palavras
)

# Adicionar o ID para conectar com a base original
if "id" in df_bow.columns:
    df_bow = df_bow.rename(columns={"id": "vocab_id"})
df_bow.insert(0, "id", df["id"].values)

# Visualizar
df_bow.head()

,id,abandoned,abby,abilities,ability,aboard,abominable,abroad,absorbing,abundant,...,zagreus,zangeki,zelda,zero,zeroes,zeus,zombie,zombies,zork,époque
0,1,0,0,0,0,0,0,0,0,0,...,0,0,0,0,0,0,0,0,0,0
1,2,0,0,0,0,0,0,0,0,0,...,0,0,0,0,0,0,0,0,0,0
2,3,0,0,0,0,0,0,0,0,0,...,0,0,0,0,0,0,0,0,0,0
3,4,0,0,0,0,0,0,0,0,0,...,0,0,0,0,0,0,0,0,0,0
4,5,0,0,0,0,0,0,0,0,0,...,0,0,0,0,0,0,0,0,0,0


## Representação 2 — TF-IDF

O **TF-IDF** também representa cada documento por meio das palavras presentes nele, mas atribui pesos diferentes às palavras.

A ideia é combinar dois fatores:

- **TF (*Term Frequency*)**: considera quanto uma palavra aparece em determinado documento;
- **IDF (*Inverse Document Frequency*)**: reduz a importância das palavras que aparecem em muitos documentos e aumenta o peso das palavras mais específicas.

Assim, uma palavra que aparece frequentemente em uma descrição, mas é rara no restante da base, tende a receber um peso relativamente alto.

Diferentemente do Bag of Words, portanto, os valores da matriz TF-IDF não representam apenas contagens. Eles indicam a **importância relativa de cada palavra em cada documento**.

Novamente, manteremos o `id` para relacionar essa representação à base original.

In [22]:
from sklearn.feature_extraction.text import TfidfVectorizer

# Criar o modelo TF-IDF
tfidf_vectorizer = TfidfVectorizer(
    analyzer=lambda tokens: tokens
)

# Criar a matriz TF-IDF
tfidf_matrix = tfidf_vectorizer.fit_transform(
    df["tokens_sem_stopwords"]
)

# Recuperar o vocabulário
tfidf_palavras = tfidf_vectorizer.get_feature_names_out()

# Transformar a matriz em DataFrame
df_tfidf = pd.DataFrame(
    tfidf_matrix.toarray(),
    columns=tfidf_palavras
)

# Adicionar o ID para conectar com a base original
if "id" in df_tfidf.columns:
    df_tfidf = df_tfidf.rename(columns={"id": "vocab_id"})
df_tfidf.insert(0, "id", df["id"].values)

# Visualizar
df_tfidf.head(20)

,id,abandoned,abby,abilities,ability,aboard,abominable,abroad,absorbing,abundant,...,zagreus,zangeki,zelda,zero,zeroes,zeus,zombie,zombies,zork,époque
0,1,0.0,0.0,0.000000,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0
1,2,0.0,0.0,0.000000,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0
2,3,0.0,0.0,0.000000,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0
3,4,0.0,0.0,0.000000,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0
4,5,0.0,0.0,0.000000,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0
5,6,0.0,0.0,0.122944,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0
6,7,0.0,0.0,0.000000,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0
7,8,0.0,0.0,0.000000,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0
8,9,0.0,0.0,0.000000,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0
9,10,0.0,0.0,0.000000,0.0,0.0,0.0,0.0,0.0,0.0,...,0.000000,0.0,0.0,0.000000,0.0,0.0,0.000000,0.0,0.0,0.0


## Similaridade entre os textos

Agora que cada descrição foi transformada em uma representação numérica, podemos comparar os documentos entre si.

Para isso, utilizaremos a **similaridade do cosseno**. Essa medida compara a direção dos vetores que representam dois textos:

- valores próximos de **1** indicam textos muito semelhantes;
- valores próximos de **0** indicam pouca semelhança;
- quanto maior o valor, maior a proximidade entre as representações.

Vamos calcular duas matrizes de similaridade:

1. uma baseada em **Bag of Words**;
2. outra baseada em **TF-IDF**.

Cada posição da matriz representa a similaridade entre dois jogos.

In [23]:
from sklearn.metrics.pairwise import cosine_similarity

# -------------------------------------------------
# Similaridade a partir do Bag of Words
# -------------------------------------------------

similaridade_bow = cosine_similarity(
    df_bow.drop(columns="id")
)

df_sim_bow = pd.DataFrame(
    similaridade_bow,
    index=df["animal"],
    columns=df["animal"]
)


# -------------------------------------------------
# Similaridade a partir do TF-IDF
# -------------------------------------------------

similaridade_tfidf = cosine_similarity(
    df_tfidf.drop(columns="id")
)

df_sim_tfidf = pd.DataFrame(
    similaridade_tfidf,
    index=df["animal"],
    columns=df["animal"]
)



In [24]:
from sklearn.metrics.pairwise import cosine_similarity

# -------------------------------------------------
# Similaridade a partir do Bag of Words
# -------------------------------------------------

similaridade_bow = cosine_similarity(
    df_bow.drop(columns="id")
)

df_sim_bow = pd.DataFrame(
    similaridade_bow,
    index=df["animal"],
    columns=df["animal"]
)


# -------------------------------------------------
# Similaridade a partir do TF-IDF
# -------------------------------------------------

similaridade_tfidf = cosine_similarity(
    df_tfidf.drop(columns="id")
)

df_sim_tfidf = pd.DataFrame(
    similaridade_tfidf,
    index=df["animal"],
    columns=df["animal"]
)


# Visualizar uma das matrizes
df_sim_bow.head()

animal,Grand Theft Auto V,Red Dead Redemption 2,Elden Ring,Minecraft: Java Edition,The Legend of Zelda: Breath of the Wild,Hollow Knight,God of War,Portal 2,Portal,Cyberpunk 2077,...,Halo: Combat Evolved,Rayman Legends,Pokémon Sword,Pokémon X,Payday 2,Slay the Spire,Final Fantasy VII,God of War II,Batman: Arkham Origins,Inscryption
animal,,,,,,,,,,,,,,,,,,,,,
Grand Theft Auto V,1.000000,0.076472,0.175562,0.053606,0.044947,0.027037,0.058026,0.052058,0.061898,0.189258,...,0.022680,0.124035,0.079119,0.160254,0.074536,0.116248,0.087039,0.035737,0.039284,0.069505
Red Dead Redemption 2,0.076472,1.000000,0.080553,0.024596,0.030934,0.037216,0.079872,0.035829,0.042601,0.148865,...,0.031220,0.056911,0.081680,0.126051,0.205196,0.053338,0.119808,0.024596,0.054074,0.047836
Elden Ring,0.175562,0.080553,1.000000,0.087837,0.189382,0.056960,0.142620,0.036558,0.021734,0.170879,...,0.031855,0.116137,0.138902,0.144692,0.052342,0.122452,0.162994,0.075289,0.082761,0.048810
Minecraft: Java Edition,0.053606,0.024596,0.087837,1.000000,0.072282,0.104352,0.037326,0.033487,0.119452,0.069568,...,0.000000,0.146277,0.063618,0.088360,0.000000,0.074778,0.055989,0.057471,0.075810,0.022355
The Legend of Zelda: Breath of the Wild,0.044947,0.030934,0.189382,0.072282,1.000000,0.043748,0.093891,0.042117,0.125196,0.065622,...,0.018349,0.050175,0.064010,0.074087,0.000000,0.031350,0.070418,0.101195,0.031782,0.084348


In [25]:
df_sim_tfidf.head()

animal,Grand Theft Auto V,Red Dead Redemption 2,Elden Ring,Minecraft: Java Edition,The Legend of Zelda: Breath of the Wild,Hollow Knight,God of War,Portal 2,Portal,Cyberpunk 2077,...,Halo: Combat Evolved,Rayman Legends,Pokémon Sword,Pokémon X,Payday 2,Slay the Spire,Final Fantasy VII,God of War II,Batman: Arkham Origins,Inscryption
animal,,,,,,,,,,,,,,,,,,,,,
Grand Theft Auto V,1.000000,0.010467,0.071320,0.009070,0.008183,0.002307,0.010129,0.007317,0.009611,0.096746,...,0.004055,0.043596,0.016118,0.028177,0.014982,0.029455,0.017095,0.005297,0.003746,0.040388
Red Dead Redemption 2,0.010467,1.000000,0.016013,0.001848,0.002562,0.003017,0.012493,0.002566,0.003370,0.067828,...,0.005303,0.028623,0.020461,0.015278,0.068457,0.008562,0.030879,0.001858,0.004899,0.003684
Elden Ring,0.071320,0.016013,1.000000,0.038272,0.123327,0.035716,0.041989,0.012062,0.001971,0.071856,...,0.026697,0.050944,0.057932,0.031735,0.013811,0.045949,0.054236,0.045906,0.034192,0.023010
Minecraft: Java Edition,0.009070,0.001848,0.038272,1.000000,0.051664,0.054029,0.021101,0.004441,0.053020,0.035069,...,0.000000,0.066475,0.023175,0.013310,0.000000,0.033492,0.021819,0.034520,0.019995,0.001710
The Legend of Zelda: Breath of the Wild,0.008183,0.002562,0.123327,0.051664,1.000000,0.016074,0.043278,0.010246,0.061530,0.031608,...,0.015108,0.018347,0.021621,0.010225,0.000000,0.008679,0.019544,0.052445,0.003153,0.041952


## Visualizando as matrizes de similaridade

Uma matriz de similaridade pode ser visualizada como um **mapa de calor (*heatmap*)**.

Cada célula compara dois jogos:

- tons mais claros indicam menor similaridade;
- tons mais escuros indicam maior similaridade.

A diagonal principal possui valor 1, pois cada descrição é perfeitamente semelhante a ela mesma.

Ao passar o mouse sobre uma célula, veremos também os dois textos que estão sendo comparados. Isso permite investigar por que determinados pares apresentam maior ou menor similaridade.

In [26]:
import plotly.graph_objects as go

# Informações que aparecerão no tooltip
animais = df["animal"].tolist()
descricoes = df["descricao"].tolist()


def criar_heatmap(matriz, titulo):

    # Criar dados adicionais para o tooltip
    customdata = []

    for i in range(len(df)):
        linha = []

        for j in range(len(df)):
            linha.append([
                animais[i],
                animais[j],
                descricoes[i],
                descricoes[j]
            ])

        customdata.append(linha)

    # Criar o heatmap
    fig = go.Figure(
        data=go.Heatmap(
            z=matriz,
            x=animais,
            y=animais,
            colorscale="Blues",
            zmin=0,
            zmax=1,
            customdata=customdata,

            hovertemplate=
                "<b>%{customdata[0]}</b><br>"
                "%{customdata[2]}<br><br>"
                "<b>%{customdata[1]}</b><br>"
                "%{customdata[3]}<br><br>"
                "<b>Similaridade:</b> %{z:.3f}"
                "<extra></extra>"
        )
    )

    fig.update_layout(
        title=titulo,
        xaxis_title="Jogo",
        yaxis_title="Jogo",
        width=900,
        height=850
    )

    fig.show()

In [27]:
criar_heatmap(
    similaridade_bow,
    "Similaridade entre descrições — Bag of Words"
)

criar_heatmap(
    similaridade_tfidf,
    "Similaridade entre descrições — TF-IDF"
)

## Agrupando os textos com K-Means

Até aqui, comparamos os textos dois a dois. Agora, vamos tentar identificar **grupos de descrições semelhantes** automaticamente.

Para isso, utilizaremos o algoritmo **K-Means**, uma técnica de clusterização que organiza os documentos em grupos com base na proximidade entre suas representações vetoriais.

Como a base possui jogos de vários gêneros, escolheremos o número de clusters automaticamente pelo **coeficiente de silhueta**:

**k = valor com maior silhueta**

É importante observar que o algoritmo **não conhece as categorias originais**. Ele recebe apenas os vetores TF-IDF e tenta formar grupos com textos semelhantes.

Depois, poderemos comparar os clusters encontrados com as categorias reais da base.

In [ ]:
from sklearn.cluster import KMeans
from sklearn.metrics import silhouette_score

# Escolher k pelo melhor coeficiente de silhueta (distância do cosseno)
silhuetas = {}
for k_teste in range(2, 13):
    rotulos_teste = KMeans(n_clusters=k_teste, random_state=42, n_init=10).fit_predict(tfidf_matrix)
    silhuetas[k_teste] = silhouette_score(tfidf_matrix, rotulos_teste, metric="cosine")

k = max(silhuetas, key=silhuetas.get)
print("Silhueta por k:", {n: round(v, 3) for n, v in silhuetas.items()})
print("k escolhido:", k)

# Criar e ajustar o modelo
kmeans = KMeans(
    n_clusters=k,
    random_state=42,
    n_init=10
)

clusters = kmeans.fit_predict(tfidf_matrix)

# Adicionar o resultado ao dataframe original
df["cluster"] = clusters

# Visualizar os resultados
df[
    ["id", "animal", "categoria", "cluster"]
].sort_values("cluster")

## Comparando clusters e categorias

Os números dos clusters são apenas identificadores arbitrários. Por exemplo, o `cluster 0` não corresponde necessariamente à primeira categoria da nossa base.

Por isso, uma forma simples de avaliar o resultado é observar quantos jogos de cada categoria foram agrupados em cada cluster.

In [29]:
comparacao_clusters = pd.crosstab(
    df["categoria"],
    df["cluster"]
)

comparacao_clusters

cluster,0,1,2
categoria,,,
Adventure,36,86,25
Arcade,0,4,0
Brawler,0,1,0
Card & Board Game,0,0,1
Fighting,0,1,2
Indie,0,6,1
MOBA,0,1,0
Platform,0,0,1
Puzzle,0,0,1


## Visualizando os clusters com PCA

Nossa representação TF-IDF possui muitas dimensões: cada palavra do vocabulário corresponde a uma dimensão.

Para visualizar a distribuição dos textos, podemos utilizar **PCA (Principal Component Analysis)**, uma técnica de redução de dimensionalidade.

O PCA cria novas dimensões que procuram preservar o máximo possível da variação existente nos dados originais.

Primeiro, reduziremos os vetores TF-IDF para **duas dimensões**. Cada ponto representará uma descrição, e sua cor indicará o cluster identificado pelo K-Means.

> Importante: o PCA será usado apenas para visualização. Os clusters já foram calculados utilizando a representação TF-IDF completa.

In [30]:
from sklearn.decomposition import PCA
import plotly.express as px

# Reduzir o TF-IDF para duas dimensões
pca_2d = PCA(n_components=2)

coordenadas_2d = pca_2d.fit_transform(
    tfidf_matrix.toarray()
)

# Criar um DataFrame para a visualização
df_pca_2d = pd.DataFrame({
    "id": df["id"],
    "animal": df["animal"],
    "categoria": df["categoria"],
    "descricao": df["descricao"],
    "cluster": df["cluster"].astype(str),
    "PCA1": coordenadas_2d[:, 0],
    "PCA2": coordenadas_2d[:, 1]
})

# Criar o gráfico
fig = px.scatter(
    df_pca_2d,
    x="PCA1",
    y="PCA2",
    color="cluster",
    hover_name="animal",
    hover_data={
        "categoria": True,
        ## "descricao": True,
        "PCA1": False,
        "PCA2": False
    },
    title="Clusters das descrições — PCA em 2 dimensões"
)

fig.update_traces(
    marker=dict(size=12)
)

fig.update_layout(
    xaxis_title="Componente principal 1",
    yaxis_title="Componente principal 2",
    legend_title="Cluster"
)

fig.show()

## Visualização em três dimensões

Podemos repetir o procedimento mantendo **três componentes principais**.

A terceira dimensão pode preservar parte da informação que foi perdida na projeção bidimensional. No gráfico interativo, podemos girar o espaço, aproximar regiões e observar os grupos sob diferentes perspectivas.

Novamente, as coordenadas PCA representam apenas uma projeção simplificada dos vetores TF-IDF.

In [31]:
# Reduzir o TF-IDF para três dimensões
pca_3d = PCA(n_components=3)

coordenadas_3d = pca_3d.fit_transform(
    tfidf_matrix.toarray()
)

# Criar DataFrame para visualização
df_pca_3d = pd.DataFrame({
    "id": df["id"],
    "animal": df["animal"],
    "categoria": df["categoria"],
    "descricao": df["descricao"],
    "cluster": df["cluster"].astype(str),
    "PCA1": coordenadas_3d[:, 0],
    "PCA2": coordenadas_3d[:, 1],
    "PCA3": coordenadas_3d[:, 2]
})

# Criar gráfico 3D
fig = px.scatter_3d(
    df_pca_3d,
    x="PCA1",
    y="PCA2",
    z="PCA3",
    color="cluster",
    hover_name="animal",
    hover_data={
        "categoria": True,
        ## "descricao": True,
        "PCA1": False,
        "PCA2": False,
        "PCA3": False
    },
    title="Clusters das descrições — PCA em 3 dimensões"
)

fig.update_traces(
    marker=dict(size=6)
)

fig.update_layout(
    scene=dict(
        xaxis_title="Componente principal 1",
        yaxis_title="Componente principal 2",
        zaxis_title="Componente principal 3"
    ),
    legend_title="Cluster"
)

fig.show()

In [32]:
print(
    "Variância explicada em 2D:",
    round(pca_2d.explained_variance_ratio_.sum(), 3)
)

print(
    "Variância explicada em 3D:",
    round(pca_3d.explained_variance_ratio_.sum(), 3)
)

Variância explicada em 2D: 0.024
Variância explicada em 3D: 0.035


## Quais palavras representam cada cluster?

O K-Means cria um **centróide** para cada cluster. Esse centróide pode ser entendido como um vetor médio que representa os documentos daquele grupo.

Como estamos trabalhando com TF-IDF, podemos inspecionar quais palavras possuem os maiores pesos em cada centróide.

Esses termos ajudam a interpretar semanticamente os clusters:

- palavras com peso alto aparecem de forma relevante nos documentos daquele grupo;
- os termos mais representativos ajudam a entender por que determinadas descrições foram agrupadas;
- essa interpretação pode ser comparada com as categorias originais dos jogos.

Vamos exibir os principais tokens de cada cluster.

In [33]:
import numpy as np

# Nomes das palavras do vocabulário TF-IDF
termos = tfidf_vectorizer.get_feature_names_out()

# Centróides calculados pelo K-Means
centroides = kmeans.cluster_centers_

# Quantidade de termos que queremos mostrar
n_termos = 8

resultados_clusters = []

for cluster_id in range(k):

    # Ordenar os termos pelo peso no centróide
    indices_ordenados = np.argsort(
        centroides[cluster_id]
    )[::-1]

    principais_indices = indices_ordenados[:n_termos]

    principais_termos = termos[principais_indices]
    principais_pesos = centroides[
        cluster_id,
        principais_indices
    ]

    resultados_clusters.append({
        "cluster": cluster_id,
        "tokens_representativos": ", ".join(principais_termos)
    })

# Criar DataFrame
df_tokens_clusters = pd.DataFrame(resultados_clusters)

df_tokens_clusters

,cluster,tokens_representativos
0,0,"world, rpg, shooter, adventure, take, tactical..."
1,1,"adventure, players, shooter, combat, gameplay,..."
2,2,"strategy, new, adventure, pokemon, based, plat..."


In [34]:
# Animais pertencentes a cada cluster
animais_por_cluster = (
    df.groupby("cluster")["animal"]
      .apply(lambda x: ", ".join(x))
      .reset_index()
)

# Juntar com os tokens representativos
df_interpretacao_clusters = df_tokens_clusters.merge(
    animais_por_cluster,
    on="cluster"
)

df_interpretacao_clusters

,cluster,tokens_representativos,animal
0,0,"world, rpg, shooter, adventure, take, tactical...","Red Dead Redemption 2, Cyberpunk 2077, Hades, ..."
1,1,"adventure, players, shooter, combat, gameplay,...","Grand Theft Auto V, Elden Ring, Minecraft: Jav..."
2,2,"strategy, new, adventure, pokemon, based, plat...","Portal, Stardew Valley, Super Smash Bros. Ulti..."


## Coesão interna dos clusters

Agora vamos avaliar o quanto os documentos de cada cluster são semelhantes entre si.

Uma forma simples de medir isso é calcular a **similaridade média entre todos os pares de textos pertencentes ao mesmo cluster**.

Interpretando o resultado:

- valores mais próximos de **1** indicam clusters mais coesos;
- valores mais baixos indicam maior diversidade interna;
- clusters com poucos documentos ou casos liminares podem apresentar menor coesão.

Como nosso agrupamento foi construído com TF-IDF, utilizaremos a similaridade do cosseno calculada a partir dessa mesma representação.

In [35]:
import numpy as np

resultados_coesao = []

for cluster_id in sorted(df["cluster"].unique()):

    # Índices dos documentos pertencentes ao cluster
    indices = df.index[df["cluster"] == cluster_id].tolist()

    # Extrair a submatriz de similaridade
    submatriz = similaridade_tfidf[np.ix_(indices, indices)]

    # Selecionar apenas a parte superior da matriz,
    # excluindo a diagonal principal
    valores_pares = submatriz[
        np.triu_indices_from(submatriz, k=1)
    ]

    # Calcular a similaridade média
    coesao_media = valores_pares.mean()

    resultados_coesao.append({
        "cluster": cluster_id,
        "n_documentos": len(indices),
        "coesao_media": coesao_media
    })


df_coesao = pd.DataFrame(resultados_coesao)

df_coesao

,cluster,n_documentos,coesao_media
0,0,49,0.028275
1,1,115,0.027205
2,2,34,0.030883


In [36]:
animais_por_cluster = (
    df.groupby("cluster")["animal"]
      .apply(lambda x: ", ".join(x))
      .reset_index()
)

df_coesao = df_coesao.merge(
    animais_por_cluster,
    on="cluster"
)

df_coesao.sort_values(
    "coesao_media",
    ascending=False
)

,cluster,n_documentos,coesao_media,animal
2,2,34,0.030883,"Portal, Stardew Valley, Super Smash Bros. Ulti..."
0,0,49,0.028275,"Red Dead Redemption 2, Cyberpunk 2077, Hades, ..."
1,1,115,0.027205,"Grand Theft Auto V, Elden Ring, Minecraft: Jav..."


## Distância entre os clusters

Além de verificar se os documentos de um cluster são semelhantes entre si, também podemos avaliar o quanto os diferentes clusters estão separados.

Para isso, vamos comparar os **centróides** produzidos pelo K-Means.

Cada centróide representa uma espécie de "posição média" dos documentos daquele cluster no espaço TF-IDF.

Utilizaremos a **distância do cosseno**:

- valores próximos de **0** indicam clusters semelhantes;
- valores maiores indicam clusters mais diferentes entre si.

A distância é calculada como:

**distância = 1 − similaridade do cosseno**

In [ ]:
from sklearn.metrics.pairwise import cosine_distances

# Distância do cosseno entre os centróides do K-Means
distancia_centroides = cosine_distances(kmeans.cluster_centers_)

pd.DataFrame(distancia_centroides).round(3)

In [38]:
resultados_distancias = []

for i in range(k):
    for j in range(i + 1, k):

        resultados_distancias.append({
            "cluster_1": i,
            "cluster_2": j,
            "distancia": distancia_centroides[i, j]
        })

df_pares_clusters = pd.DataFrame(
    resultados_distancias
)

df_pares_clusters.sort_values("distancia")

NameError: name 'distancia_centroides' is not defined

## Clusters mais próximos e mais distantes

A matriz de distância permite identificar dois casos especialmente interessantes:

- o par de clusters com **menor distância**, isto é, os grupos mais semelhantes entre si;
- o par com **maior distância**, isto é, os grupos mais diferentes.

Vamos identificar esses pares e listar os jogos presentes em cada cluster.

In [ ]:
# Identificar menor e maior distância entre clusters
par_mais_proximo = df_pares_clusters.loc[
    df_pares_clusters["distancia"].idxmin()
]

par_mais_distante = df_pares_clusters.loc[
    df_pares_clusters["distancia"].idxmax()
]


def animais_do_cluster(cluster_id):
    return df.loc[
        df["cluster"] == cluster_id,
        "animal"
    ].tolist()


# Clusters mais próximos
c1_prox = int(par_mais_proximo["cluster_1"])
c2_prox = int(par_mais_proximo["cluster_2"])

# Clusters mais distantes
c1_dist = int(par_mais_distante["cluster_1"])
c2_dist = int(par_mais_distante["cluster_2"])


print("CLUSTERS MAIS PRÓXIMOS")
print("----------------------")
print(
    f"Cluster {c1_prox} × Cluster {c2_prox}"
)
print(
    f"Distância: {par_mais_proximo['distancia']:.3f}"
)
print(
    f"Cluster {c1_prox}: {', '.join(animais_do_cluster(c1_prox))}"
)
print(
    f"Cluster {c2_prox}: {', '.join(animais_do_cluster(c2_prox))}"
)


print("\nCLUSTERS MAIS DISTANTES")
print("-----------------------")
print(
    f"Cluster {c1_dist} × Cluster {c2_dist}"
)
print(
    f"Distância: {par_mais_distante['distancia']:.3f}"
)
print(
    f"Cluster {c1_dist}: {', '.join(animais_do_cluster(c1_dist))}"
)
print(
    f"Cluster {c2_dist}: {', '.join(animais_do_cluster(c2_dist))}"
)

CLUSTERS MAIS PRÓXIMOS
----------------------
Cluster 3 × Cluster 6
Distância: 0.504
Cluster 3: God of War, Cyberpunk 2077, Marvel's Spider-Man, Hades, Super Mario Odyssey, Grand Theft Auto: San Andreas, Marvel's Spider-Man: Miles Morales, Detroit: Become Human, Batman: Arkham Knight, The Legend of Zelda: Tears of the Kingdom, Dark Souls: Remastered, Fallout: New Vegas, Super Smash Bros. Brawl, Dishonored, Hotline Miami, Marvel's Spider-Man 2, Super Mario World, Super Mario Bros., Devil May Cry 5, Assassin's Creed III, Metal Gear Rising: Revengeance, Watch Dogs, Yakuza 0, Assassin's Creed Brotherhood, Outer Wilds, Rise of the Tomb Raider, Assassin's Creed Origins, Dispatch, South Park: The Stick of Truth, Super Mario Bros. Wonder, God of War III, Batman: Arkham Origins
Cluster 6: Grand Theft Auto V, Elden Ring, Minecraft: Java Edition, Hollow Knight, Portal 2, Undertale, Resident Evil 2, The Elder Scrolls V: Skyrim, Dark Souls III, The Witcher 3: Wild Hunt, Terraria, Cuphead, Celeste, 

## Conclusão

Neste notebook, exploramos uma sequência completa de análise de texto, desde a preparação inicial até o agrupamento e a interpretação dos resultados.

Vimos como:

- Preparar textos para análise, incluindo tokenização, normalização e remoção de *stopwords*.
- Criar representações numéricas de texto usando **Bag of Words** e **TF-IDF**, e como a última é mais robusta ao considerar a importância relativa das palavras.
- Calcular a **similaridade do cosseno** para comparar documentos, destacando as diferenças entre as representações BoW e TF-IDF.
- Utilizar o algoritmo **K-Means** para agrupar documentos semelhantes, mesmo sem conhecimento prévio das categorias.
- Visualizar esses clusters por meio de **PCA em 2D e 3D**, o que ajuda a entender a separação e coesão dos grupos.
- Interpretar os clusters analisando os **termos mais representativos** de cada centróide e a **coesão interna** dos clusters.
- Avaliar a **distância entre os centróides** para identificar os clusters mais semelhantes e mais distintos.

Essas técnicas são fundamentais para diversas aplicações em PLN, como sistemas de recomendação, busca e categorização automática de documentos.